In [ ]:
# @title Copyright 2026 Google LLC
#
# Licensed under the Apache License, Version 2.0 (the "License");
# you may not use this file except in compliance with the License.
# You may obtain a copy of the License at
#
#     https://www.apache.org/licenses/LICENSE-2.0
#
# Unless required by applicable law or agreed to in writing, software
# distributed under the License is distributed on an "AS IS" BASIS,
# WITHOUT WARRANTIES OR CONDITIONS OF ANY KIND, either express or implied.
# See the License for the specific language governing permissions and
# limitations under the License.

# Intro to Gemini Live Avatar

<table align="left">
  <td style="text-align: center">
    <a href="https://colab.research.google.com/github/GoogleCloudPlatform/generative-ai/blob/main/gemini/multimodal-live-api/intro_live_avatar.ipynb">
      <img width="32px" src="https://www.gstatic.com/pantheon/images/bigquery/welcome_page/colab-logo.svg" alt="Google Colaboratory logo"><br> Open in Colab
    </a>
  </td>
  <td style="text-align: center">
    <a href="https://console.cloud.google.com/agent-platform/colab/import/https:%2F%2Fraw.githubusercontent.com%2FGoogleCloudPlatform%2Fgenerative-ai%2Fmain%2Fgemini%2Fmultimodal-live-api%2Fintro_live_avatar.ipynb">
      <img width="32px" src="https://lh3.googleusercontent.com/JmcxdQi-qOpctIvWKgPtrzZdJJK-J3sWE1RsfjZNwshCFgE_9fULcNpuXYTilIR2hjwN" alt="Google Cloud Colab Enterprise logo"><br> Open in Colab Enterprise
    </a>
  </td>
  <td style="text-align: center">
    <a href="https://console.cloud.google.com/agent-platform/workbench/instances?download_url=https://raw.githubusercontent.com/GoogleCloudPlatform/generative-ai/main/gemini/multimodal-live-api/intro_live_avatar.ipynb">
      <img width="32px" src="https://storage.googleapis.com/github-repo/workbench-icon.svg" alt="Workbench logo"><br> Open in Workbench
    </a>
  </td>
  <td style="text-align: center">
    <a href="https://github.com/GoogleCloudPlatform/generative-ai/blob/main/gemini/multimodal-live-api/intro_live_avatar.ipynb">
      <img width="32px" src="https://raw.githubusercontent.com/primer/octicons/refs/heads/main/icons/mark-github-24.svg" alt="GitHub logo"><br> View on GitHub
    </a>
  </td>
</table>

<div style="clear: both;"></div>

<p>
<b>Share to:</b>

<a href="https://www.linkedin.com/sharing/share-offsite/?url=https%3A//github.com/GoogleCloudPlatform/generative-ai/blob/main/gemini/multimodal-live-api/intro_live_avatar.ipynb" target="_blank">
  <img width="20px" src="https://upload.wikimedia.org/wikipedia/commons/8/81/LinkedIn_icon.svg" alt="LinkedIn logo">
</a>

<a href="https://bsky.app/intent/compose?text=https%3A//github.com/GoogleCloudPlatform/generative-ai/blob/main/gemini/multimodal-live-api/intro_live_avatar.ipynb" target="_blank">
  <img width="20px" src="https://upload.wikimedia.org/wikipedia/commons/7/7a/Bluesky_Logo.svg" alt="Bluesky logo">
</a>

<a href="https://twitter.com/intent/tweet?url=https%3A//github.com/GoogleCloudPlatform/generative-ai/blob/main/gemini/multimodal-live-api/intro_live_avatar.ipynb" target="_blank">
  <img width="20px" src="https://upload.wikimedia.org/wikipedia/commons/5/5a/X_icon_2.svg" alt="X logo">
</a>

<a href="https://reddit.com/submit?url=https%3A//github.com/GoogleCloudPlatform/generative-ai/blob/main/gemini/multimodal-live-api/intro_live_avatar.ipynb" target="_blank">
  <img width="20px" src="https://redditinc.com/hubfs/Reddit%20Inc/Brand/Reddit_Logo.png" alt="Reddit logo">
</a>

<a href="https://www.facebook.com/sharer/sharer.php?u=https%3A//github.com/GoogleCloudPlatform/generative-ai/blob/main/gemini/multimodal-live-api/intro_live_avatar.ipynb" target="_blank">
  <img width="20px" src="https://upload.wikimedia.org/wikipedia/commons/5/51/Facebook_f_logo_%282019%29.svg" alt="Facebook logo">
</a>
</p>

| Authors |
| --- |
| [Eric Dong](https://github.com/gericdong) |
| [Holt Skinner](https://github.com/holtskinner) |

## Overview

**Gemini Live Avatar** is a feature of the Gemini Live API that synthesizes real-time, synchronized video of an AI-driven character.

Instead of delivering only audio responses, the API generates a video stream where the avatar's lip movements and facial expressions are perfectly synced to the generated speech. This allows developers to build low-latency, "face-to-face" conversational experiences using either a library of high-quality stock avatars or custom reference images provided by the user.

This notebook demonstrates two ways to connect to the Live API and request Gemini to return a synthesized video of an avatar speaking the response by specifying an `avatar_config` and enabling the `VIDEO` response modality.

1. **Via Standard WebSockets**: Constructing raw JSON payloads to stream audio/video and manage turn completion.
2. **Via the Google Gen AI SDK**: Using the official Python library to handle messages seamlessly.

## Getting Started

### Install required libraries

In [1]:
%pip install --upgrade --quiet --no-warn-conflicts google-genai

⚠️ **Note**: Ignore pip dependency errors.

### Import libraries

In [2]:
import asyncio
import base64
import json
import os
import requests
import sys
import websockets

from IPython.display import Audio, display, Video

from google import genai
from google.genai import types

from pathlib import Path
from IPython.display import Video
from google.genai import types

### Authenticate your notebook environment

If you are running this notebook on Google Colab, run the cell below to authenticate your environment.

In [3]:
if "google.colab" in sys.modules:
    from google.colab import auth

    auth.authenticate_user()

### Set Google Cloud project information

To get started using Agent Platform, you must have an existing Google Cloud project and [enable the Agent Platform API](https://console.cloud.google.com/flows/enableapi?apiid=aiplatform.googleapis.com).

Learn more about [setting up a project](https://docs.cloud.google.com/resource-manager/docs/creating-managing-projects) and a [development environment](https://cloud.google.com/docs/authentication/set-up-adc-local-dev-environment).

In [4]:
# fmt: off
PROJECT_ID = "[your-project-id]"  # @param {type: "string", placeholder: "[your-project-id]", isTemplate: true}
# fmt: on
if not PROJECT_ID or PROJECT_ID == "[your-project-id]":
    PROJECT_ID = str(os.environ.get("GOOGLE_CLOUD_PROJECT"))

LOCATION = "us-central1"  # @param {type: "string", placeholder: "global"}

### Choose a Gemini model

In [5]:
# fmt: off
MODEL_ID = "gemini-3.8-live"  # @param {type: "string"}
# fmt: on

## 🚀 Live Avatar via WebSocket

This implementation uses standard WebSockets to construct the raw JSON payloads needed to enable the Live Avatar feature and process the resulting audio and video chunks.

This example uses one of the built-in avatars by specifying the avatar name in the avatar config. It also uses one of the [supported voice options](https://docs.cloud.google.com/gemini-enterprise-agent-platform/models/live-api/configure-language-voice#voices-supported) for live avatar.

In [6]:
# Authentication
token_list = !gcloud auth application-default print-access-token
headers = {"Authorization": f"Bearer {token_list[0]}"}

# Full path to the specific Gemini Live model
MODEL = f"projects/{PROJECT_ID}/locations/{LOCATION}/publishers/google/models/{MODEL_ID}"

# Enable VIDEO modality to generate Avatars
CONFIG = {
    "responseModalities": ["VIDEO"],
    "speechConfig": {
        "voiceConfig": {
            "prebuiltVoiceConfig": {
                "voiceName": "Puck" # Options: Puck, Aoede, Charon, Kore, Fenrir, Zephyr
            }
        }
    }
}

# Avatar Configuration
# Use a built-in avatar (Examples: Jay, Paul, Sam, Ingrid, Kira, Vera, Ben, Kai, Leo, Carmen, Piper)
AVATAR_CONFIG = {
   "avatar_name": "Ben"
}

# Construct the WSS URL for the Live API endpoint
HOST = f"{LOCATION}-aiplatform.googleapis.com"
URI = f"wss://{HOST}/ws/google.cloud.aiplatform.v1.LlmBidiService/BidiGenerateContent"

async def main():
    print("Connecting to the Gemini Live API via standard WebSockets...")
    async with websockets.connect(URI, additional_headers=headers) as ws:

        # 1. Send the Setup message
        setup_msg = {
            "setup": {
                "systemInstruction": {"parts": [{"text": "You are a helpful AI assistant."}]},
                "model": MODEL,
                "generationConfig": CONFIG,
                "avatarConfig": AVATAR_CONFIG,
            }
        }
        await ws.send(json.dumps(setup_msg))
        await ws.recv()
        print("Session established. Sending text message...")

        # 2. Send the User's input
        user_msg = {
            "realtime_input": {
                "text": "Hi, are you there?"
            }
        }
        await ws.send(json.dumps(user_msg))

        video_data = []

        # 3. Process the server's streaming response
        async for message in ws:
            response = json.loads(message)
            parts = response.get("serverContent", {}).get("modelTurn", {}).get("parts", [])

            # Extract inline video frame data
            for part in parts:
                if "inlineData" in part:
                    # Video frames are returned as base64 strings, so they must be decoded
                    video_data.append(base64.b64decode(part["inlineData"]["data"]))

            # Check if the turn is complete
            server_content = response.get("serverContent")
            is_turn_complete = server_content is not None and (server_content.get("turnComplete"))

            if is_turn_complete:
                print(f"Turn complete. Total video frames received: {len(video_data)}")
                if video_data:
                    output_file = "output_video.mp4"
                    with open(output_file, "wb") as f:
                        f.write(b"".join(video_data))

                    # Display the output with autoplay attributes
                    display(Video(output_file, embed=True, width=600, height=400, html_attributes="controls autoplay"))
                break

# Execute the asynchronous main function in the notebook
await main()

Connecting to the Gemini Live API via standard WebSockets...
Session established. Sending text message...
Turn complete. Total video frames received: 281


## 🚀 Live Avatar via Gen AI SDK

This alternative uses the **Google Gen AI SDK** to handle messages seamlessly.

In [7]:
# Initialize the GenAI Client
client = genai.Client(
    enterprise=True,
    project=PROJECT_ID,
    location=LOCATION,
    http_options={'base_url': 'https://us-central1-aiplatform.googleapis.com'},
)

In [8]:
async def generate_avatar_video(
    prompt: str,
    config: types.LiveConnectConfig,
    output_file: str = "output_video_sdk.mp4",
):
    print("Connecting to the Gemini Live API via the Google Gen AI SDK...")
    # Establish a live connect session
    async with client.aio.live.connect(model=MODEL_ID, config=config) as session:
        print("Session established. Sending text message...")

        await session.send_realtime_input(text="Tell me a joke about a rabbit?")

        video_data = []

        async for message in session.receive():
            if message.server_content:
                if message.server_content.interrupted:
                    continue
                # Accumulate the video parts from the model's turn
                model_turn = message.server_content.model_turn
                if model_turn and model_turn.parts:
                    for part in model_turn.parts:
                        if part.inline_data:
                          # The SDK already decodes the binary base64 data for us
                          video_data.append(part.inline_data.data)

            # Check if this turn has completed
            if message.server_content.turn_complete:
                print(f"Turn complete. Total video frames received: {len(video_data)}")
                if video_data:
                    with open(output_file, "wb") as f:
                        f.write(b"".join(video_data))

                    # Display the output with autoplay and muted attributes
                    display(Video(output_file, embed=True, width=600, height=400, html_attributes="controls autoplay"))
                break


# Configure the LiveConnect Session for VIDEO modality, avatar, and speech (voice)
config = types.LiveConnectConfig(
    response_modalities=["VIDEO"],
    system_instruction="You are a hilarious comedian.",
    avatar_config=types.AvatarConfig(avatar_name="Kai"),
    speech_config=types.SpeechConfig(
        voice_config=types.VoiceConfig(
            prebuilt_voice_config=types.PrebuiltVoiceConfig(
                voice_name="Puck"
            )
        )
    )
)
# Execute the asynchronous SDK function in the notebook
prompt = "Tell me a joke about a Rabbit"
await generate_avatar_video(prompt, config)

Connecting to the Gemini Live API via the Google Gen AI SDK...
Session established. Sending text message...
Turn complete. Total video frames received: 345


## 🚀 Custom Avatar

Instead of using a pre-built avatar, you can use your own customized avatar image, by specifying the image in the avatar config.

This example uses a photo of one of the existing avatars as a custom avatar, for demo purposes.


In [9]:
custom_avatar_url = "https://storage.googleapis.com/cloud-samples-data/generative-ai/image/kira.png"
response = requests.get(custom_avatar_url)

custom_avatar_b64_img = base64.b64encode(response.content).decode('utf-8')

In [10]:
# Configuration
config=types.LiveConnectConfig(
    response_modalities=["VIDEO"],
    system_instruction="You are a helpful AI assistant.",
    avatar_config=types.AvatarConfig(
        customized_avatar=types.CustomizedAvatar(image_mime_type="image/jpeg", image_data=custom_avatar_b64_img) # Custom avatar
    ),
    speech_config=types.SpeechConfig(
        voice_config=types.VoiceConfig(
            prebuilt_voice_config=types.PrebuiltVoiceConfig(
                voice_name="Aoede", # Options: Puck, Aoede, Charon, Kore, Fenrir, Zephyr
            )
        ),
    ),
)

prompt = "Tell me a joke about a Rabbit"
await generate_avatar_video(prompt, config)

Connecting to the Gemini Live API via the Google Gen AI SDK...
Session established. Sending text message...
Turn complete. Total video frames received: 290
